In [1]:
from lib_data import Round3Data,P3Round3Data,Round3DataBacktest
from lib_plots import BigPicture, Picture, plotly_colors
from lib_signal import ma,smile_pred_impl_vol,smile_pred_price,moneyness,impl_vol,fit,pred,prem
from p4 import Trader
from tqdm import tqdm
import numpy as np
data = Round3Data(cached=True)
# Ks = [9500,9750,10000,10250,10500]
# Ks = [4000, 4500, 5000, 5100, 5200, 5300, 5400, 5500, 6000, 6500]
Ks = [5000,5100,5200,5300,5400,5500]

In [2]:
Kcs = dict(zip(Ks,plotly_colors))
fig = BigPicture(1,400,share_x=True)
ms = []
sigmas = []
sms = []
ssigmas = []
for K in Ks:
    prems = prem(data.V(K),data.S(),K)
    mask = np.logical_and(prems>0, data.timestamps()<1000000_00)
    V,S,TTE = data.V(K)[mask],data.S()[mask],data.TTE()[mask]
    m = moneyness(S,K,TTE)
    sigma = impl_vol(V,S,K,TTE)
    stuff = [(i,sigma[i],prems[i]) for i in range(len(sigma))]
    pic = Picture(m,[0]*len(m))
    pic.add_cross(f"{K}",
        stuff=stuff,
        i=lambda p:p[0],
        y=lambda p:p[1],
        l=lambda p,x,y:f"t={p[0]},prem={p[2]}",
        color=[f"hsla({i/len(stuff)*140},90,50,0.01)" for i,s,p in stuff],
    )
    # if 5000<=K<=5500 and K != 5400:
    if 1:
        ms += list(m[[s[0] for s in stuff]])
        sigmas += [s[1] for s in stuff]
    # if 5000<=K<=5500:
    if 1:
        sms += list(m[[s[0] for s in stuff]])
        ssigmas += [s[1] for s in stuff]
        fig.add(pic,1)
# a,b,c=fit(ms,sigmas,2)
# print(a,b,c,sep=",")
# pic = Picture(sms,[0]*len(sms))
# pic.add_line(f"fitted_line",pred(sms,a,b,c))
# fig.add(pic,1)
fig.show()

In [6]:
import plotly.graph_objects as go
import numpy as np

all_ms = []
all_TTEs = []
all_sigmas = []

for K in Ks:
    prems = prem(data.V(K), data.S(), K)
    mask = np.logical_and(prems > 0, data.timestamps() < 1000000_00)
    V, S, TTE = data.V(K)[mask], data.S()[mask], data.TTE()[mask]
    m = moneyness(S, K, TTE)
    sigma = impl_vol(V, S, K, TTE)
    all_ms += list(m)
    all_TTEs += list(TTE)
    all_sigmas += list(sigma)

all_ms = np.array(all_ms)
all_TTEs = np.array(all_TTEs)
all_sigmas = np.array(all_sigmas)

fig = go.Figure(data=[
    go.Scatter3d(
        x=all_ms, y=all_TTEs, z=all_sigmas,
        mode='markers',
        marker=dict(
            size=2,
            color=all_sigmas,
            colorscale='RdYlGn_r',
            colorbar=dict(title='Implied Vol'),
            opacity=0.5,
        ),
    )
])

fig.update_layout(
    height=700,
    scene=dict(
        xaxis_title='Moneyness',
        yaxis_title='Time to Expiry',
        zaxis_title='Implied Vol',
        camera=dict(eye=dict(x=1.5, y=-1.5, z=0.8)),
    ),
    title='Implied Volatility Surface',
    margin=dict(l=0, r=0, b=0, t=40),
)
fig.show()

In [8]:
import plotly.graph_objects as go
import numpy as np
from scipy.optimize import curve_fit

all_ms = []
all_TTEs = []
all_sigmas = []
all_ms_fit = []
all_TTEs_fit = []
all_sigmas_fit = []

for K in Ks:
    prems = prem(data.V(K), data.S(), K)
    mask = np.logical_and(prems > 0, data.timestamps() < 1000000_00)
    V, S, TTE = data.V(K)[mask], data.S()[mask], data.TTE()[mask]
    m = moneyness(S, K, TTE)
    sigma = impl_vol(V, S, K, TTE)
    all_ms += list(m)
    all_TTEs += list(TTE)
    all_sigmas += list(sigma)
    if K != 5400:
        all_ms_fit += list(m)
        all_TTEs_fit += list(TTE)
        all_sigmas_fit += list(sigma)

all_ms = np.array(all_ms)
all_TTEs = np.array(all_TTEs)
all_sigmas = np.array(all_sigmas)
all_ms_fit = np.array(all_ms_fit)
all_TTEs_fit = np.array(all_TTEs_fit)
all_sigmas_fit = np.array(all_sigmas_fit)

# Fit: quadratic in moneyness + linear in TTE
def vol_surface(X, a, b, c, d, e):
    m, tte = X
    return a + b*m + c*m**2 + d*tte + e*m*tte

popt, _ = curve_fit(vol_surface, (all_ms_fit, all_TTEs_fit), all_sigmas_fit, maxfev=10000)

# Evaluate on a grid
m_grid = np.linspace(all_ms.min(), all_ms.max(), 60)
tte_grid = np.linspace(all_TTEs.min(), all_TTEs.max(), 60)
M, T = np.meshgrid(m_grid, tte_grid)
sigma_grid = vol_surface((M.ravel(), T.ravel()), *popt).reshape(M.shape)

sigma_fitted = vol_surface((all_ms, all_TTEs), *popt)
residuals = all_sigmas - sigma_fitted

fig = go.Figure(data=[
    go.Scatter3d(
        x=all_ms, y=all_TTEs, z=residuals,
        mode='markers',
        marker=dict(size=2, color=residuals, colorscale='RdBu', cmid=0, opacity=0.5),
        name='Residuals',
    )
])

fig.update_layout(
    height=700,
    scene=dict(
        xaxis_title='Moneyness',
        yaxis_title='Time to Expiry',
        zaxis_title='IV Residual',
        camera=dict(eye=dict(x=1.5, y=-1.5, z=0.8)),
    ),
    title='Implied Vol Residuals vs Fitted Surface (excl. K=5400 from fit)',
    margin=dict(l=0, r=0, b=0, t=40),
)
fig.show()

In [9]:
from scipy.optimize import curve_fit

def vol_surface(X, a, b, c, d, e):
    m, tte = X
    return a + b*m + c*m**2 + d*tte + e*m*tte

all_ms_fit = []
all_TTEs_fit = []
all_sigmas_fit = []

for K in Ks:
    if K == 5400:
        continue
    prems = prem(data.V(K), data.S(), K)
    mask = np.logical_and(prems > 0, data.timestamps() < 1000000_00)
    V, S, TTE = data.V(K)[mask], data.S()[mask], data.TTE()[mask]
    m = moneyness(S, K, TTE)
    sigma = impl_vol(V, S, K, TTE)
    all_ms_fit += list(m)
    all_TTEs_fit += list(TTE)
    all_sigmas_fit += list(sigma)

popt, _ = curve_fit(vol_surface, (np.array(all_ms_fit), np.array(all_TTEs_fit)), np.array(all_sigmas_fit), maxfev=10000)
a, b, c, d, e = popt
print(f"a={a}, b={b}, c={c}, d={d}, e={e}")

a=0.01330605977637028, b=0.0038293429398075086, c=0.001201017807027063, d=-8.979584275308355e-05, e=-0.000470803230326497


In [2]:
fig = BigPicture(1+1,2*1800,share_x=True)
pic = Picture(data.timestamps(),data.zeros())
pic.add_line("S", data.S())
fig.add(pic,1)
for i,K in enumerate(Ks):
    prems = prem(data.V(K),data.S(),K)
    V,S,TTE = data.V(K)[prems>0],data.S()[prems>0],data.TTE()[prems>0]
    sigma = impl_vol(V,S,K,TTE)
    stuff = [(i,sigma[i],prems[i]) for i in range(len(sigma))]
    # theo = smile_pred_impl_vol(S,K,TTE,a,b,c)
    pic = Picture(data.timestamps()[prems>0],data.zeros()[prems>0])
    pic.add_line(f"{K}", sigma)
    # pic.add_cross(f"{K}",
    #     stuff=stuff,
    #     i=lambda p:p[0],
    #     y=lambda p:p[1],
    #     l=lambda p,x,y:f"t={p[0]},prem={p[2]}",
    #     color=Kcs[K]
    # )
    # pic.add_line(f"theo_{K}",theo)
    fig.add(pic,2)
fig.show()